# Slope-refit candidate review

This notebook is a read-only review gate for the isolated candidate contexts. It does **not** alter hydraulic contexts, resistance products, RAPID inputs, or network geometry.

The queue deliberately avoids treating every lower-cap transition as a defect. It selects: (1) all new upper-cap links; (2) direct-profile connectors whose slope changes by at least a factor of 20; and (3) compact solved domains whose **entire** slope field changes by at least a factor of five and includes a factor-20 change.

In [1]:
from pathlib import Path

import geopandas as gpd
import numpy as np
import pandas as pd
import plotly.graph_objects as go
from IPython.display import display, Markdown

CANDIDATE_ROOT = Path('/Volumes/PhD/river_hierarchy/network_variants/output/_slope_refit_candidates')
BASE_OUTPUT_ROOT = Path('/Volumes/PhD/river_hierarchy/network_variants/output')
IMPACT_PATH = CANDIDATE_ROOT / 'impact_v1' / 'slope_refit_candidate_link_impact.parquet'
BATCH_MANIFEST_PATH = CANDIDATE_ROOT / 'slope_refit_candidate_batch_manifest.csv'

if not IMPACT_PATH.exists():
    raise FileNotFoundError(f'Missing candidate impact product: {IMPACT_PATH}')

impact = pd.read_parquet(IMPACT_PATH).copy()
impact['example_id'] = impact['example_id'].astype(str).str.zfill(2)
batch_manifest = pd.read_csv(BATCH_MANIFEST_PATH)
batch_manifest['example_id'] = batch_manifest['example_id'].astype(str).str.zfill(2)
EXPERIMENT_DIR_BY_ID = batch_manifest.set_index('example_id')['experiment_dir'].map(Path).to_dict()
impact['slope_change_factor'] = np.maximum(
    pd.to_numeric(impact['slope_ratio_candidate_to_current'], errors='coerce'),
    1.0 / pd.to_numeric(impact['slope_ratio_candidate_to_current'], errors='coerce'),
)
print(f'Loaded {len(impact):,} comparable candidate links across {impact.example_id.nunique()} examples.')

Loaded 5,315 comparable candidate links across 16 examples.


In [2]:
# Build the transparent, small review queue. These are review triggers, not failure labels.
UPPER_CAP = impact['candidate_celerity_cap_status'].eq('above_max_cap')
DIRECT_EXTREME = (
    impact['candidate_domain_kind'].eq('direct_profile')
    & impact['slope_change_factor'].ge(20.0)
)

domain_columns = ['example_id', 'candidate_domain_kind', 'candidate_domain_id']
solved = impact.loc[~impact['candidate_domain_kind'].eq('direct_profile')].copy()
domain_screen = solved.groupby(domain_columns, dropna=False).agg(
    n_links=('id_link', 'size'),
    min_slope_change_factor=('slope_change_factor', 'min'),
    median_slope_change_factor=('slope_change_factor', 'median'),
    max_slope_change_factor=('slope_change_factor', 'max'),
    n_factor_20=('slope_change_factor', lambda values: int(values.ge(20.0).sum())),
    max_path_residual_m=('candidate_domain_path_residual_m', 'max'),
).reset_index()
domain_queue = domain_screen.loc[
    domain_screen['min_slope_change_factor'].ge(5.0)
    & domain_screen['max_slope_change_factor'].ge(20.0)
].sort_values(['max_slope_change_factor', 'example_id'], ascending=[False, True]).reset_index(drop=True)

review_links = impact.loc[UPPER_CAP | DIRECT_EXTREME].copy()
review_links['review_reason'] = np.select(
    [UPPER_CAP.loc[review_links.index], DIRECT_EXTREME.loc[review_links.index]],
    ['new_upper_celerity_cap', 'extreme_direct_profile_connector'],
    default='combined_trigger',
)
link_columns = [
    'example_id', 'id_link', 'review_reason', 'candidate_domain_kind', 'candidate_domain_id',
    'current_slope_m_per_m', 'candidate_slope_m_per_m', 'slope_ratio_candidate_to_current',
    'slope_change_factor', 'current_celerity_cap_status', 'candidate_celerity_cap_status',
    'candidate_numerical_floor_active', 'candidate_domain_path_residual_m',
]
display(Markdown(f'## Link-level review: {len(review_links)} links'))
display(review_links[link_columns].sort_values(['review_reason', 'slope_change_factor'], ascending=[True, False]))
display(Markdown(f'## Domain-level review: {len(domain_queue)} compact domains'))
display(domain_queue)

## Link-level review: 14 links

,example_id,id_link,review_reason,candidate_domain_kind,candidate_domain_id,current_slope_m_per_m,candidate_slope_m_per_m,slope_ratio_candidate_to_current,slope_change_factor,current_celerity_cap_status,candidate_celerity_cap_status,candidate_numerical_floor_active,candidate_domain_path_residual_m
538,13,174,extreme_direct_profile_connector,direct_profile,NaN,0.000380,9.547859e-07,0.002511,398.183323,rapid_config_unavailable,rapid_config_unavailable,False,NaN
4029,46,196,extreme_direct_profile_connector,direct_profile,NaN,0.000091,1.302031e-06,0.014302,69.919027,within_cap_range,below_min_cap,False,NaN
1207,21,50,extreme_direct_profile_connector,direct_profile,NaN,0.000005,2.718306e-04,59.575524,59.575524,below_min_cap,within_cap_range,False,NaN
1609,22,15,extreme_direct_profile_connector,direct_profile,NaN,0.000116,2.298136e-06,0.019756,50.617919,within_cap_range,below_min_cap,False,NaN
1661,22,12,extreme_direct_profile_connector,direct_profile,NaN,0.000116,2.298136e-06,0.019756,50.617919,within_cap_range,below_min_cap,False,NaN
4117,46,284,extreme_direct_profile_connector,direct_profile,NaN,0.000064,1.302031e-06,0.020412,48.989881,within_cap_range,below_min_cap,False,NaN
1254,22,45,extreme_direct_profile_connector,direct_profile,NaN,0.000078,2.298136e-06,0.029444,33.962615,within_cap_range,below_min_cap,False,NaN
1311,22,30,extreme_direct_profile_connector,direct_profile,NaN,0.000078,2.298136e-06,0.029444,33.962615,within_cap_range,below_min_cap,False,NaN
3296,41,95,extreme_direct_profile_connector,direct_profile,NaN,0.000020,8.746664e-07,0.043766,22.848600,within_cap_range,below_min_cap,False,NaN
4598,54,38,extreme_direct_profile_connector,direct_profile,NaN,0.000019,3.898955e-04,20.637551,20.637551,below_min_cap,within_cap_range,False,NaN


## Domain-level review: 14 compact domains

,example_id,candidate_domain_kind,candidate_domain_id,n_links,min_slope_change_factor,median_slope_change_factor,max_slope_change_factor,n_factor_20,max_path_residual_m
0,11,simple_unit,18.0,2,325.695220,325.695220,325.695220,2,0.0
1,46,compound_bubble,63.0,8,80.831578,80.831578,80.831578,8,0.0
2,22,simple_unit,5.0,2,56.652790,56.901211,57.149633,2,0.0
3,21,simple_unit,16.0,2,46.445898,46.445898,46.445898,2,0.0
4,22,simple_unit,10.0,2,40.208427,40.208427,40.208427,2,0.0
5,05,simple_unit,13.0,2,39.646865,39.646865,39.646865,2,0.0
6,22,compound_bubble,8.0,14,39.493475,39.493475,39.493475,14,0.0
7,22,simple_unit,6.0,2,36.734470,37.523203,38.311936,2,0.0
8,11,simple_unit,20.0,2,14.981593,23.693282,32.404971,1,0.0
9,21,simple_unit,9.0,2,30.596872,30.596872,30.596872,2,0.0


## Select one review object

Use a `direct_profile` selection for one of the listed connector links. For a solved-domain selection, use the exact kind and ID from `domain_queue`. The default is the four new upper-cap links in Example 37, compound bubble 3.

In [53]:
REVIEW_EXAMPLE_ID = '46'  # e.g. '21'       
REVIEW_DOMAIN_KIND = 'direct_profile'  # 'compound_bubble', 'simple_unit', or 'direct_profile'
REVIEW_DOMAIN_ID = None                 # use None for direct_profile
REVIEW_LINK_IDS = [196]                 # optional: e.g. [100, 348, 420, 566] or [174]

def base_directed_links(example_id):
    directed = EXPERIMENT_DIR_BY_ID[example_id] / 'states' / 'S000_base' / 'variant' / 'directed'
    matches = sorted(path for path in directed.glob('*directed_links.gpkg') if not path.name.startswith('._'))
    if len(matches) != 1:
        raise FileNotFoundError(f'Expected one directed-links GPKG in {directed}; found {matches}')
    return gpd.read_file(matches[0])

selected = impact.loc[impact['example_id'].eq(REVIEW_EXAMPLE_ID)].copy()
if REVIEW_DOMAIN_KIND == 'direct_profile':
    selected = selected.loc[selected['candidate_domain_kind'].eq('direct_profile')].copy()
elif REVIEW_DOMAIN_ID is not None:
    selected = selected.loc[
        selected['candidate_domain_kind'].eq(REVIEW_DOMAIN_KIND)
        & pd.to_numeric(selected['candidate_domain_id'], errors='coerce').eq(float(REVIEW_DOMAIN_ID))
    ].copy()
if REVIEW_LINK_IDS:
    selected = selected.loc[selected['id_link'].isin(REVIEW_LINK_IDS)].copy()
if selected.empty:
    raise ValueError('Selection is empty. Copy an example/domain/link from one of the review tables above.')

selected['log10_slope_ratio'] = np.log10(selected['slope_ratio_candidate_to_current'])
selection_columns = [column for column in link_columns if column != 'review_reason'] + ['candidate_slope_source_method']
display(selected[selection_columns].sort_values('id_link'))

,example_id,id_link,candidate_domain_kind,candidate_domain_id,current_slope_m_per_m,candidate_slope_m_per_m,slope_ratio_candidate_to_current,slope_change_factor,current_celerity_cap_status,candidate_celerity_cap_status,candidate_numerical_floor_active,candidate_domain_path_residual_m,candidate_slope_source_method
4029,46,196,direct_profile,NaN,0.000091,0.000001,0.014302,69.919027,within_cap_range,below_min_cap,False,NaN,frozen_profile_direct_connector_or_boundary


In [54]:
# Plan view: all base links grey; selected review links coloured by log10(candidate/current slope).
links = base_directed_links(REVIEW_EXAMPLE_ID).merge(
    selected[['id_link', 'log10_slope_ratio', 'current_slope_m_per_m', 'candidate_slope_m_per_m']],
    on='id_link', how='left', validate='1:1',
)
metric = links['log10_slope_ratio'].dropna()
colour_limit = max(0.3, float(metric.abs().max()) if len(metric) else 0.3)

def line_xy(geometry):
    if geometry is None or geometry.is_empty:
        return [], []
    if geometry.geom_type == 'LineString':
        xy = np.asarray(geometry.coords)
        return xy[:, 0].tolist(), xy[:, 1].tolist()
    xs, ys = [], []
    for part in geometry.geoms:
        xy = np.asarray(part.coords); xs.extend(xy[:, 0].tolist() + [None]); ys.extend(xy[:, 1].tolist() + [None])
    return xs, ys

fig = go.Figure()
for row in links.loc[links['log10_slope_ratio'].isna()].itertuples():
    x, y = line_xy(row.geometry)
    fig.add_scatter(x=x, y=y, mode='lines', line={'color': 'rgba(80,80,80,0.20)', 'width': 1}, hoverinfo='skip', showlegend=False)
for row in links.loc[links['log10_slope_ratio'].notna()].itertuples():
    x, y = line_xy(row.geometry)
    ratio = float(row.log10_slope_ratio)
    colour = 'crimson' if ratio > 0 else 'royalblue'
    fig.add_scatter(
        x=x, y=y, mode='lines', name=f'link {int(row.id_link)}',
        line={'color': colour, 'width': 4},
        hovertemplate=(f'link {int(row.id_link)}<br>log10(candidate/current)={ratio:.3f}' '<extra></extra>'),
    )
fig.update_layout(
    title=f'Example {REVIEW_EXAMPLE_ID}: selected slope-refit review object',
    xaxis={'visible': False}, yaxis={'visible': False, 'scaleanchor': 'x', 'scaleratio': 1},
    legend_title='Selected links: red = steeper candidate; blue = flatter candidate', height=700,
)
fig.show()

In [55]:
# Longitudinal evidence: raw pass observations, stage-aligned values, fitted profile, and candidate heads.
profile_dir = CANDIDATE_ROOT / 'profiles' / REVIEW_EXAMPLE_ID
context_dir = CANDIDATE_ROOT / 'candidate_contexts' / REVIEW_EXAMPLE_ID
profile = pd.read_parquet(profile_dir / 'reference_profile.parquet')
observations = pd.read_parquet(profile_dir / 'reference_profile_observations.parquet')
candidate_nodes = pd.read_parquet(context_dir / 'candidate_node_hydraulic_context.parquet')
selected_node_ids = sorted(set(selected['id_us_node'].astype(int)) | set(selected['id_ds_node'].astype(int)))
selected_nodes = candidate_nodes.loc[candidate_nodes['id_node'].isin(selected_node_ids)].copy()

# Keep this responsive for the largest observation populations without changing any statistics.
plot_observations = observations
if len(plot_observations) > 30000:
    plot_observations = plot_observations.sample(30000, random_state=0)

fig = go.Figure()
fig.add_scatter(
    x=plot_observations['reference_section_dist_out_m'], y=plot_observations['wse_m'],
    mode='markers', name='raw RiverSP/SWOT pass WSE',
    marker={'size': 3, 'color': 'rgba(80,80,80,0.17)'},
)
fig.add_scatter(
    x=plot_observations['reference_section_dist_out_m'], y=plot_observations['stage_aligned_wse_m'],
    mode='markers', name='stage-aligned pass WSE',
    marker={'size': 3, 'color': 'rgba(60,130,220,0.12)'},
)
fig.add_scatter(x=profile['reference_section_dist_out_m'], y=profile['static_wse_m'], mode='lines', name='static P50 reference', line={'color': 'darkorange', 'width': 1.5})
fig.add_scatter(x=profile['reference_section_dist_out_m'], y=profile['fitted_wse_m'], mode='lines', name='accepted fitted profile', line={'color': 'black', 'width': 3})
fig.add_scatter(
    x=selected_nodes['reference_section_dist_out_m'], y=selected_nodes['candidate_head_m'],
    mode='markers+text', name='candidate domain heads', text=selected_nodes['id_node'].astype(str), textposition='top center',
    marker={'size': 10, 'color': 'crimson'},
)
fig.update_layout(
    title=f'Example {REVIEW_EXAMPLE_ID}: longitudinal evidence for the selected object',
    xaxis_title='Distance to outlet [m]', yaxis_title='WSE [m]', height=700,
)
fig.show()

display(selected_nodes.sort_values('reference_section_dist_out_m'))

,id_node,reference_section_dist_out_m,reference_section_dist_source,profile_head_m,candidate_head_m,candidate_head_source_method
135,135,381332.789800,geometry_projection_reference_section,248.638125,248.638125,frozen_reference_profile_direct
136,136,384941.511178,geometry_projection_reference_section,248.642824,248.642824,frozen_reference_profile_direct


In [56]:
# Celerity sensitivity only. This does not fit or endorse a Kb value.
# c ∝ n^-1 Kb^(-2/3) sqrt(S): n=0.035 is compared to the stored n/Kb configuration.
sensitivity = selected.copy()
sensitivity['celerity_at_n_0035_same_kb_mps'] = (
    sensitivity['candidate_celerity_mps_raw'] * sensitivity['n_manning_used'] / 0.035
)
# The cap is recoverable from raw and capped celerity for a currently upper-capped row.
upper = sensitivity.loc[sensitivity['candidate_celerity_cap_status'].eq('above_max_cap')].copy()
if upper.empty:
    display(Markdown('No selected link is above its stored maximum cap; the n/Kb sensitivity table remains available.'))
    sensitivity['kb_required_to_reach_stored_max_cap'] = np.nan
else:
    stored_max_cap = float(upper['candidate_celerity_mps_capped'].iloc[0])
    sensitivity['kb_required_to_reach_stored_max_cap'] = (
        sensitivity['kb_value_used']
        * np.power(sensitivity['celerity_at_n_0035_same_kb_mps'] / stored_max_cap, 1.5)
    )
    display(Markdown(f'Stored maximum cap inferred from selected upper-capped rows: **{stored_max_cap:g} m/s**.'))

display(sensitivity[[
    'id_link', 'candidate_slope_m_per_m', 'candidate_celerity_mps_raw', 'candidate_celerity_cap_status',
    'n_manning_used', 'kb_value_used', 'celerity_at_n_0035_same_kb_mps', 'kb_required_to_reach_stored_max_cap',
]].sort_values('id_link'))

No selected link is above its stored maximum cap; the n/Kb sensitivity table remains available.

,id_link,candidate_slope_m_per_m,candidate_celerity_mps_raw,candidate_celerity_cap_status,n_manning_used,kb_value_used,celerity_at_n_0035_same_kb_mps,kb_required_to_reach_stored_max_cap
4029,196,0.000001,0.009291,below_min_cap,0.35,238.845514,0.092913,NaN


## Decision rule

Accept a selected object when its candidate heads follow the accepted fitted profile, its domain paths retain the same boundary head loss (already checked numerically), and the map does not expose an ownership/topology mismatch. A large difference from the current slope is expected where the old context used a fallback or a near-zero local slope; it is not, by itself, a reason to reject the candidate.

Do not tune (K_b) to make a selected link pass a cap. (K_b) is a hydraulic calibration/geometry quantity and must be selected independently. The sensitivity panel only makes that dependence explicit.